### Map the growth rates of the postcodes

In [1]:
import geopandas as gpd
import pandas as pd

sf = gpd.read_file("../data/landing/postcode/POA_2021_AUST_GDA2020.shp")


In [2]:
sf.head()

,POA_CODE21,POA_NAME21,AUS_CODE21,AUS_NAME21,AREASQKM21,LOCI_URI21,SHAPE_Leng,SHAPE_Area,geometry
0,0800,0800,AUS,Australia,3.1731,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.081893,0.000264,"POLYGON ((130.83681 -12.45376, 130.83684 -12.4..."
1,0810,0810,AUS,Australia,24.4283,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.241859,0.002031,"POLYGON ((130.89986 -12.36567, 130.89875 -12.3..."
2,0812,0812,AUS,Australia,35.8899,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.278788,0.002983,"POLYGON ((130.91915 -12.40786, 130.91831 -12.4..."
3,0820,0820,AUS,Australia,39.0642,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.409134,0.003248,"POLYGON ((130.85260 -12.43994, 130.85089 -12.4..."
4,0822,0822,AUS,Australia,150775.8030,http://linked.data.gov.au/dataset/asgsed3/POA/...,90.601831,12.564238,"MULTIPOLYGON (((136.56648 -12.08392, 136.56704..."


Filter the VIC suburbs

In [3]:
vic_suburbs = sf[sf["POA_CODE21"].astype(str).str.startswith('3')]

In [4]:
geoJSON = vic_suburbs[['POA_CODE21', 'geometry']].drop_duplicates('POA_CODE21').to_json()

In [5]:
import folium

In [6]:
rent_data = pd.read_csv("../data/curated/weekly_rent_2023_and_2026.csv")

In [7]:
rent_data.head()

,postcode,weekly rent amount 2023,weekly rent amount 2026,growth_rate
0,3000,671.313536,673.14716,0.002731
1,3002,809.151515,704.01495,-0.129934
2,3003,600.779070,684.12680,0.138733
3,3004,709.277108,705.88696,-0.004780
4,3006,713.786667,646.61690,-0.094103


In [8]:
type(vic_suburbs.iloc[1]["POA_CODE21"])

str

Change the Postcodes to integer types

In [9]:
vic_suburbs["POA_CODE21"] = vic_suburbs["POA_CODE21"].astype(int)

/root/anaconda3/lib/python3.11/site-packages/geopandas/geodataframe.py:1538: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame.
Try using .loc[row_indexer,col_indexer] = value instead

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  super().__setitem__(key, value)


In [10]:
rent_data["postcode"] = rent_data["postcode"].astype(int)

Merge the datasets on Postcodes

In [47]:
gdf = gpd.GeoDataFrame(
    rent_data.merge(vic_suburbs, right_on='POA_CODE21', left_on='postcode', how='left')
)

Change the geometry to lat and long and find the centroid of each Postcode

In [50]:
gdf['geometry'] = gdf['geometry'].to_crs("+proj=longlat +ellps=WGS84 +datum=WGS84 +no_defs")

In [51]:
gdf['centroid'] = gdf['geometry'].apply(lambda x: (x.centroid.y, x.centroid.x))

In [44]:
gdf.head()

,postcode,weekly rent amount 2023,weekly rent amount 2026,growth_rate,POA_CODE21,POA_NAME21,AUS_CODE21,AUS_NAME21,AREASQKM21,LOCI_URI21,SHAPE_Leng,SHAPE_Area,geometry,centroid
0,3000,671.313536,673.14716,0.002731,3000,3000,AUS,Australia,2.4814,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.083491,0.000254,"POLYGON ((144.96139 -37.82050, 144.96063 -37.8...","(-37.81314234745685, 144.96238093177988)"
1,3002,809.151515,704.01495,-0.129934,3002,3002,AUS,Australia,1.8557,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.059488,0.000190,"POLYGON ((144.98978 -37.81906, 144.98973 -37.8...","(-37.81441916677731, 144.98259335231918)"
2,3003,600.779070,684.12680,0.138733,3003,3003,AUS,Australia,6.5822,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.139928,0.000673,"POLYGON ((144.95268 -37.81280, 144.95191 -37.8...","(-37.80931496260727, 144.9252035754352)"
3,3004,709.277108,705.88696,-0.004780,3004,3004,AUS,Australia,4.0421,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.137947,0.000414,"POLYGON ((144.98001 -37.84422, 144.98031 -37.8...","(-37.83252018902255, 144.97732514913363)"
4,3006,713.786667,646.61690,-0.094103,3006,3006,AUS,Australia,1.8542,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.066882,0.000190,"POLYGON ((144.96139 -37.82050, 144.96303 -37.8...","(-37.82575445789247, 144.96066244098998)"


In [12]:
rent_data.head()

,postcode,weekly rent amount 2023,weekly rent amount 2026,growth_rate
0,3000,671.313536,673.14716,0.002731
1,3002,809.151515,704.01495,-0.129934
2,3003,600.779070,684.12680,0.138733
3,3004,709.277108,705.88696,-0.004780
4,3006,713.786667,646.61690,-0.094103


In [13]:
df = gdf[["POA_CODE21", 'growth_rate']]

In [24]:
m = folium.Map(location=[-37.020100, 144.964600], tiles="Stamen Terrain", zoom_start=7)


# refer to the folium documentations on more information on how to plot aggregated data.
c = folium.Choropleth(
    geo_data=geoJSON, # geoJSON 
    name='choropleth', # name of plot
    data=df.reset_index(), # data source
    columns=["POA_CODE21", 'growth_rate'], # the columns required
    key_on= 'properties.POA_CODE21', # this is from the geoJSON's properties
    fill_color='viridis', # color scheme
    bins=10,
    nan_fill_color='white',
    legend_name='Growth rate of Weekly Rent'
)

c.add_to(m)

m


Get the top 10 suburbs and plot them on the map

In [32]:
top_10_suburbs = df.sort_values(by = "growth_rate", ascending=False)["POA_CODE21"][:10].values

In [33]:
top_10_suburbs

array([3638, 3318, 3477, 3988, 3289, 3612, 3666, 3579, 3796, 3377])

In [34]:
gdf.head()

,postcode,weekly rent amount 2023,weekly rent amount 2026,growth_rate,POA_CODE21,POA_NAME21,AUS_CODE21,AUS_NAME21,AREASQKM21,LOCI_URI21,SHAPE_Leng,SHAPE_Area,geometry,centroid
0,3000,671.313536,673.14716,0.002731,3000,3000,AUS,Australia,2.4814,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.083491,0.000254,"POLYGON ((144.96139 -37.82050, 144.96063 -37.8...",POINT (144.96238 -37.81314)
1,3002,809.151515,704.01495,-0.129934,3002,3002,AUS,Australia,1.8557,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.059488,0.000190,"POLYGON ((144.98978 -37.81906, 144.98973 -37.8...",POINT (144.98259 -37.81442)
2,3003,600.779070,684.12680,0.138733,3003,3003,AUS,Australia,6.5822,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.139928,0.000673,"POLYGON ((144.95268 -37.81280, 144.95191 -37.8...",POINT (144.92520 -37.80931)
3,3004,709.277108,705.88696,-0.004780,3004,3004,AUS,Australia,4.0421,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.137947,0.000414,"POLYGON ((144.98001 -37.84422, 144.98031 -37.8...",POINT (144.97733 -37.83252)
4,3006,713.786667,646.61690,-0.094103,3006,3006,AUS,Australia,1.8542,http://linked.data.gov.au/dataset/asgsed3/POA/...,0.066882,0.000190,"POLYGON ((144.96139 -37.82050, 144.96303 -37.8...",POINT (144.96066 -37.82575)


In [35]:
gdf.loc[gdf["postcode"] == 3638]

,postcode,weekly rent amount 2023,weekly rent amount 2026,growth_rate,POA_CODE21,POA_NAME21,AUS_CODE21,AUS_NAME21,AREASQKM21,LOCI_URI21,SHAPE_Leng,SHAPE_Area,geometry,centroid
278,3638,180.0,763.2262,3.240146,3638,3638,AUS,Australia,445.6388,http://linked.data.gov.au/dataset/asgsed3/POA/...,1.911302,0.044563,"POLYGON ((145.22280 -36.13404, 145.22092 -36.1...",POINT (145.16900 -36.03493)


In [52]:
for suburb in top_10_suburbs:
    coord = gdf.loc[gdf["postcode"] == suburb]["centroid"].values
    m.add_child(
        folium.Marker(location=coord)
    )
    
m